#Automatic drum transcription with ADTOF

Instructions:
* This Notebook contains three cells: Setup, Transcribe, Visualize.
* Press ▶️ on the first cell (Setup) to install the code repository and the transcription model
* Restart the environment when requested
* Then click on Runtime>Run all
* A video is generated at the end of the document.

In [ ]:
#@title Setup (takes 2 min)

!pip install adtof@git+https://github.com/MZehren/ADTOF
!pip install yt-dlp

  Cloning https://github.com/MZehren/ADTOF to /tmp/pip-install-u_gbm5rw/adtof_298e9f3177cf421cbbb17b4281b183cd
  Running command git clone --filter=blob:none --quiet https://github.com/MZehren/ADTOF /tmp/pip-install-u_gbm5rw/adtof_298e9f3177cf421cbbb17b4281b183cd
  Resolved https://github.com/MZehren/ADTOF to commit b3968fb332f69b65ee07c089fc62f436503755db
  Preparing metadata (setup.py) ... done
  Cloning https://github.com/MZehren/tapcorrect to /tmp/pip-install-u_gbm5rw/tapcorrect_9506955eaa32475393147b142c373891
  Running command git clone --filter=blob:none --quiet https://github.com/MZehren/tapcorrect /tmp/pip-install-u_gbm5rw/tapcorrect_9506955eaa32475393147b142c373891
  Resolved https://github.com/MZehren/tapcorrect to commit 4f2d21e73fb0137119a4136513c42936b322fc0b
  Preparing metadata (setup.py) ... done
  Cloning https://github.com/CPJKU/madmom to /tmp/pip-install-u_gbm5rw/madmom_c9bb2439ec294c9cb8567c08108062ac
  Running command git clone --filter=blob:none --quiet https://g

In [ ]:
#@title Transcribe (takes 1min)
#@markdown Download a video from Youtube
import yt_dlp
import os
from google.colab import files
import shutil



url = "http://www.youtube.com/watch?v=plueIrKgRcE" #@param {type:"string"}
outtmpl = 'in/video.webm' # removed "%title" and "%ext" because title would not match infos[title]
videoPath = 'in/video.webm'
mp3Path = 'in/video.mp3'
scorePath = 'out/video.webm.mp3.txt'

 # remove existing file if it exists because name is hardcoded
if os.path.exists(scorePath):
  os.remove(scorePath)
if os.path.exists("in"):
  shutil.rmtree('in')

ydl_opts = {
    # "format": "bestaudio/best",
    "format": "b[filesize<20M] / w",
    "postprocessors": [{"key": "FFmpegExtractAudio", "preferredcodec": "mp3", "preferredquality": "192"}],
    'keepvideo': 'True',
    "outtmpl": outtmpl,
    "gettitle": 1,
}
with yt_dlp.YoutubeDL(ydl_opts) as ydl:
  infos = ydl.extract_info(url)


# Fix for Keras 3 legacy optimizer issue
!pip install tf_keras
os.environ["TF_USE_LEGACY_KERAS"] = "True"

#@markdown Transcribe the audio
from adtof.model.model import Model

modelName = "Frame_RNN" #@param ["Frame_RNN"]
model, hparams = Model.modelFactory(modelName=modelName, scenario="adtofAll", fold=0)
print("peakThreshold", hparams["peakThreshold"])
model.predictFolder("in/*.mp3", "out", **hparams)

downloadTranscription = True #@param {type:"boolean"}
if downloadTranscription:
  files.download(scorePath) #TODO change the title to info[title]

[youtube] Extracting URL: http://www.youtube.com/watch?v=plueIrKgRcE
[youtube] plueIrKgRcE: Downloading webpage


[youtube] plueIrKgRcE: Downloading android vr player API JSON
[info] plueIrKgRcE: Downloading 1 format(s): 18
[download] Destination: in/video.webm
[download] 100% of   12.48MiB in 00:00:00 at 25.05MiB/s  
[ExtractAudio] Destination: in/video.webm.mp3
peakThreshold [0.22000000000000003, 0.24000000000000002, 0.32000000000000006, 0.22000000000000003, 0.30000000000000004]


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>

In [ ]:
#@title Visualize (takes 2min)
print("Generate animation")
import pandas as pd
import matplotlib.pyplot as plt
from matplotlib.animation import FuncAnimation, FFMpegWriter
from IPython import display
from matplotlib.collections import PatchCollection
import numpy as np

# ------ Parameters
score = pd.read_csv(scorePath, delimiter = "\t", header=None, names=["X", "Y"])
fps = 5#@param {type:"integer"}
frames = int(infos["duration"]*fps) #int((score["X"].iloc[-1]+window)*fps/10)
window = 4
lookAhead = 3.8

# ------- Prepare plot
fig = plt.Figure(figsize=(15,2))
classToY = {35:0.5, 38:2.5, 42:4.5, 47:3.5, 49:5.5}
axis = fig.add_subplot(xlim=(0, window), ylim=(-1, 6))
axis.set_yticks(list(classToY.values()))
axis.set_yticklabels(["BD", "SD", "HH", "TT", "CY+RD"])
drum, = axis.plot([], [], "o", color="black", markersize=8)
HH, = axis.plot([], [], "x", color="black", markersize=8)
CY, = axis.plot([], [], "*", color="black", markersize=8)
vline, = axis.plot([], [], color="red", lw=2)
for i in range(5):
  staff = axis.axhline(i, color="black", lw=1)
oldStart = -1

# Animate
def animate(frame):
    # Animate cursor
    start = frame/fps // lookAhead*lookAhead
    cursor =  frame/fps
    end = start + window
    vline.set_data([cursor, cursor], [-1, 6])

    # Animate staff
    global oldStart
    if oldStart != start: #update only when view changed
        oldStart = start
        for line, classes in zip([drum, HH, CY], [set([35,38,47]),set([42]),set([49])]):
            xy = np.array([[x, classToY[y]] for x,y in zip(score["X"], score["Y"]) if x>start and x<end and y in classes])
            x = xy[:,0] if len(xy) else []
            y = xy[:,1] if len(xy) else []
            axis.set_xlim(start, end)
            line.set_data(x, y)
        return drum, HH, CY, vline
    return vline
anim = FuncAnimation(fig, animate, frames=frames, interval=1000/fps)

# ------ save animation in mp4
FFwriter = FFMpegWriter(fps=fps)
animationPath = 'out/animation.mp4'
anim.save(animationPath, writer=FFwriter)

print("Merge original video and animation")

if os.path.exists("out/overlay.mp4"): # remove existing file if it exists because name is hardcoded
  os.remove("out/overlay.mp4")

!ffmpeg  -i in/video.webm -i out/animation.mp4 -filter_complex '[0:v]scale=1280:trunc(ow/a/2)*2[main];[1:v]scale=1280:trunc(ow/a/2)*2[overlay];[main][overlay]overlay=(main_w-overlay_w):(main_h-overlay_h)' -c:v libx264 -fs 20M -preset ultrafast out/overlay.mp4

print("Display result in the cell")

from IPython.display import HTML
from base64 import b64encode
mp4 = open('out/overlay.mp4','rb').read()
data_url = "data:video/mp4;base64," + b64encode(mp4).decode()
HTML("""
<video width=1024 controls>
      <source src="%s" type="video/mp4">
</video>
""" % data_url)

Generate animation
Merge original video and animation
ffmpeg version 4.4.2-0ubuntu0.22.04.1 Copyright (c) 2000-2021 the FFmpeg developers
  built with gcc 11 (Ubuntu 11.2.0-19ubuntu1)
  configuration: --prefix=/usr --extra-version=0ubuntu0.22.04.1 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --enable-gnutls --enable-ladspa --enable-libaom --enable-libass --enable-libbluray --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libgme --enable-libgsm --enable-libjack --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-libpulse --enable-librabbitmq --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libsrt --enable-libssh --enable-libtheora --enable-libtwolame --enabl